# V1: train first, then evaluate
Run setup and configuration first. If no trained V1 exists, WORKFLOW selects train: run the two training cells, then the two evaluation cells. If a local/Colab final already exists, WORKFLOW selects evaluate and training cells print a skip message. Full training starts only when you execute its cell. Validation/test-run weights are never selected.

In [1]:
from pathlib import Path
import sys, json
here = Path.cwd().resolve()
PROJECT = next((p for p in [here, *here.parents] if (p/'asr/config.py').is_file()), None)
if PROJECT is None:
    PROJECT = next((p/'ASR' for p in [here, *here.parents] if (p/'ASR/asr/config.py').is_file()), None)
assert PROJECT is not None, 'Open notebook from the project workspace'
PYTHON = PROJECT.parent/'.venv-asr/Scripts/python.exe'
DATA = PROJECT/'data'
RAW_DATA = PROJECT.parent/'dataset/ASR'
assert PYTHON.is_file(), 'Run ASR/local/setup.ps1 first'
sys.path.insert(0, str(PROJECT/'local'))
from notebook_process import run_cli as _run_cli
def run_cli(arguments):
    return _run_cli(PROJECT, PYTHON, arguments)
RUNNER = PROJECT/'scripts/local_run.py'
print('Project:', PROJECT)
print('Python:', PYTHON)
print('Ready. Run the specific task cell; model jobs do not start in this setup cell.')


Project: D:\1.FPT_FALL26\DPL - Deep Learning\ASR
Python: D:\1.FPT_FALL26\DPL - Deep Learning\.venv-asr\Scripts\python.exe
Ready. Run the specific task cell; model jobs do not start in this setup cell.


In [2]:
EXP = 'V1_phowhisper_small_lora'
LOCAL_FINAL = PROJECT/'local/runs'/EXP/'local_v1/final'
COLAB_FINAL = PROJECT/'experiments'/EXP/'final'

def find_v1_checkpoint():
    # Do not use validation_* or train_smoke weights as a trained V1.
    for path in [LOCAL_FINAL, COLAB_FINAL]:
        if (path/'adapter_config.json').is_file() and (path/'adapter_model.safetensors').is_file():
            return path
    return None

CHECKPOINT = find_v1_checkpoint()
WORKFLOW = 'evaluate' if CHECKPOINT is not None else 'train'
print('Workflow:', WORKFLOW)
print('Checkpoint:', CHECKPOINT if CHECKPOINT else 'Not available yet; train V1 first.')
print('Local training output:', LOCAL_FINAL)
print('To reuse Colab V1, copy its entire final directory to:', COLAB_FINAL)
print('Only change WORKFLOW to train if you want a local training run.')
run_cli([RUNNER, 'check', EXP])


Workflow: train
Checkpoint: Not available yet; train V1 first.
Local training output: D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\runs\V1_phowhisper_small_lora\local_v1\final
To reuse Colab V1, copy its entire final directory to: D:\1.FPT_FALL26\DPL - Deep Learning\ASR\experiments\V1_phowhisper_small_lora\final
Only change WORKFLOW to train if you want a local training run.
[START] "D:\1.FPT_FALL26\DPL - Deep Learning\.venv-asr\Scripts\python.exe" -u "D:\1.FPT_FALL26\DPL - Deep Learning\ASR\scripts\local_run.py" check V1_phowhisper_small_lora
[LOG] D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\logs\20261018_170724_316772.log
[INIT] mode=check experiment=V1_phowhisper_small_lora; importing PyTorch/ASR libraries...
{
  "python": "D:\\1.FPT_FALL26\\DPL - Deep Learning\\.venv-asr\\Scripts\\python.exe",
  "cuda": true,
  "versions": {
    "torch": "2.6.0+cu124",
    "transformers": "4.46.3",
    "peft": "0.13.2",
    "accelerate": "1.1.1",
    "datasets": "3.1.0"
  },
  "missing_data": []

## 1. Training (only when WORKFLOW = train)
First run the two-step smoke cell. If successful, run full training. This starts from the pretrained base or resumes this local run; it does not continue optimizer state from a Colab final adapter. Checkpoints: ASR/local/runs/V1_phowhisper_small_lora/local_v1/checkpoints. Best adapter: local_v1/final. Existing Colab final is preserved.

In [3]:
if WORKFLOW == 'train':
    print('TRAIN SMOKE: 2 optimizer steps; diagnostic weights only.', flush=True)
    run_cli([RUNNER, 'train', EXP, '--run-id', 'train_smoke', '--smoke'])
else:
    print('Skipping training: using the existing trained V1 checkpoint.')


TRAIN SMOKE: 2 optimizer steps; diagnostic weights only.
[START] "D:\1.FPT_FALL26\DPL - Deep Learning\.venv-asr\Scripts\python.exe" -u "D:\1.FPT_FALL26\DPL - Deep Learning\ASR\scripts\local_run.py" train V1_phowhisper_small_lora --run-id train_smoke --smoke
[LOG] D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\logs\20261018_170730_282057.log
[INIT] mode=train experiment=V1_phowhisper_small_lora; importing PyTorch/ASR libraries...
{
  "python": "D:\\1.FPT_FALL26\\DPL - Deep Learning\\.venv-asr\\Scripts\\python.exe",
  "cuda": true,
  "versions": {
    "torch": "2.6.0+cu124",
    "transformers": "4.46.3",
    "peft": "0.13.2",
    "accelerate": "1.1.1",
    "datasets": "3.1.0"
  },
  "missing_data": [],
  "profile": {
    "total_gpu_budget_gb": 4.5,
    "gpu_duty_cycle": 0.7,
    "host_ram_budget_gb": 0,
    "save_steps": 100,
    "checkpoint_interval_seconds": 600,
    "save_total_limit": 2,
    "batch_size": 1,
    "grad_accum": 32,
    "num_workers": 0
  },
  "local_v1_final": false,
  

In [4]:
if WORKFLOW == 'train':
    print('FULL V1 TRAINING: fresh base or resume local_v1; checkpoint saving is enabled.', flush=True)
    run_cli([RUNNER, 'train', EXP, '--run-id', 'local_v1'])
    CHECKPOINT = find_v1_checkpoint()
    print('Trained checkpoint:', CHECKPOINT)
else:
    print('Skipping training. Continue to the evaluation cells below.')


FULL V1 TRAINING: fresh base or resume local_v1; checkpoint saving is enabled.
[START] "D:\1.FPT_FALL26\DPL - Deep Learning\.venv-asr\Scripts\python.exe" -u "D:\1.FPT_FALL26\DPL - Deep Learning\ASR\scripts\local_run.py" train V1_phowhisper_small_lora --run-id local_v1
[LOG] D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\logs\20261018_170854_868263.log
[INIT] mode=train experiment=V1_phowhisper_small_lora; importing PyTorch/ASR libraries...
{
  "python": "D:\\1.FPT_FALL26\\DPL - Deep Learning\\.venv-asr\\Scripts\\python.exe",
  "cuda": true,
  "versions": {
    "torch": "2.6.0+cu124",
    "transformers": "4.46.3",
    "peft": "0.13.2",
    "accelerate": "1.1.1",
    "datasets": "3.1.0"
  },
  "missing_data": [],
  "profile": {
    "total_gpu_budget_gb": 4.5,
    "gpu_duty_cycle": 0.7,
    "host_ram_budget_gb": 0,
    "save_steps": 100,
    "checkpoint_interval_seconds": 600,
    "save_total_limit": 2,
    "batch_size": 1,
    "grad_accum": 32,
    "num_workers": 0
  },
  "local_v1_final"

## 2. Evaluation (after training or importing Colab final)
Run the smoke evaluation first, then full DEV. Checkpoint paths are rechecked in each cell, so no kernel restart is required after training finishes. If no checkpoint exists, these cells explain the missing prerequisite without starting the evaluator.

In [5]:
CHECKPOINT = find_v1_checkpoint()
if CHECKPOINT is None:
    print('Evaluation not started: no trained V1 checkpoint exists yet.')
    print('Run TRAIN SMOKE then FULL V1 TRAINING above, or import the complete Colab final directory.')
else:
    EVAL_TAG = 'local_v1' if CHECKPOINT == LOCAL_FINAL else 'colab_v1'
    print('SMOKE EVALUATION checkpoint:', CHECKPOINT, flush=True)
    run_cli([RUNNER, 'eval', EXP, '--run-id', 'smoke_' + EVAL_TAG,
             '--max-per-source', '2', '--checkpoint', CHECKPOINT])


SMOKE EVALUATION checkpoint: D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\runs\V1_phowhisper_small_lora\local_v1\final
[START] "D:\1.FPT_FALL26\DPL - Deep Learning\.venv-asr\Scripts\python.exe" -u "D:\1.FPT_FALL26\DPL - Deep Learning\ASR\scripts\local_run.py" eval V1_phowhisper_small_lora --run-id smoke_local_v1 --max-per-source 2 --checkpoint "D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\runs\V1_phowhisper_small_lora\local_v1\final"
[LOG] D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\logs\20261019_212913_255842.log
[INIT] mode=eval experiment=V1_phowhisper_small_lora; importing PyTorch/ASR libraries...
[RUNNING] 11s elapsed; waiting for the next model/data update.
{
  "python": "D:\\1.FPT_FALL26\\DPL - Deep Learning\\.venv-asr\\Scripts\\python.exe",
  "cuda": true,
  "versions": {
    "torch": "2.6.0+cu124",
    "transformers": "4.46.3",
    "peft": "0.13.2",
    "accelerate": "1.1.1",
    "datasets": "3.1.0"
  },
  "missing_data": [],
  "profile": {
    "total_gpu_budget_gb": 4.5,


In [6]:
CHECKPOINT = find_v1_checkpoint()
if CHECKPOINT is None:
    print('Full DEV evaluation not started: train V1 or import its Colab final directory first.')
else:
    EVAL_TAG = 'local_v1' if CHECKPOINT == LOCAL_FINAL else 'colab_v1'
    print('FULL DEV EVALUATION checkpoint:', CHECKPOINT, flush=True)
    run_cli([RUNNER, 'eval', EXP, '--run-id', 'dev_' + EVAL_TAG,
             '--checkpoint', CHECKPOINT])


FULL DEV EVALUATION checkpoint: D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\runs\V1_phowhisper_small_lora\local_v1\final
[START] "D:\1.FPT_FALL26\DPL - Deep Learning\.venv-asr\Scripts\python.exe" -u "D:\1.FPT_FALL26\DPL - Deep Learning\ASR\scripts\local_run.py" eval V1_phowhisper_small_lora --run-id dev_local_v1 --checkpoint "D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\runs\V1_phowhisper_small_lora\local_v1\final"
[LOG] D:\1.FPT_FALL26\DPL - Deep Learning\ASR\local\logs\20261019_212959_408882.log
[INIT] mode=eval experiment=V1_phowhisper_small_lora; importing PyTorch/ASR libraries...
{
  "python": "D:\\1.FPT_FALL26\\DPL - Deep Learning\\.venv-asr\\Scripts\\python.exe",
  "cuda": true,
  "versions": {
    "torch": "2.6.0+cu124",
    "transformers": "4.46.3",
    "peft": "0.13.2",
    "accelerate": "1.1.1",
    "datasets": "3.1.0"
  },
  "missing_data": [],
  "profile": {
    "total_gpu_budget_gb": 4.5,
    "gpu_duty_cycle": 0.7,
    "host_ram_budget_gb": 0,
    "save_steps": 100,
  